# NeuroGati Video Engine — Orchestrator

Runs the pipeline one stage at a time so you can inspect, **edit on disk, and re-load**
your edits before approving and continuing.

**Script Block (implemented):** Planner → Detailed Scripter → Audio-Visual Scene Script.
**Audio branch (implemented):** Audio Generator — Piper TTS + Whisper word-level timestamps, per scene.
**Visual branch (not built yet):** prompt maker → scene code generator → render → critique.

**Editing workflow, script stages:** each stage writes its output to a plain file under
`projects/<slug>/`. Open it in any editor, change whatever you want, save, then run that
stage's *reload* cell — it optionally expands rough edits back to full detail (via
`utils/prompt_enhancer.py`), then injects your edited text back into the pipeline before you
resume to the next stage. Skip the reload cell if you're happy with the output as generated.
The Audio stage has no text reload step — to change a scene's narration, edit
`03_scenes.json`, reload, then re-run Step 4.

In [5]:
import json
from pathlib import Path

from IPython.display import Audio, HTML, Markdown, Video, display

from state import Scene, VideoState
from workflow import build_graph
from utils.storage import project_dir, save_state
from utils.references import list_reference_files, load_references
from utils.prompt_enhancer import enhance
from agents.planner import revise_plan
from agents.detailed_scripter import revise_script
from agents.scene_script import revise_scenes
from agents.visual_render import RENDERERS

BADGE_COLOR = {
    "manim": "#2f6fed",
    "matplotlib": "#1fa971",
    "image_only": "#c98a1f",
    "audio_only": "#8a5fd1",
}

RENDERED_TYPES = {"manim", "matplotlib"}


def show_scenes(scenes):
    rows = []
    for s in scenes:
        color = BADGE_COLOR.get(s.scene_type, "#888")
        rows.append(f'''
        <div style="border:1px solid #444;border-radius:8px;padding:12px;margin-bottom:10px;">
          <div style="display:flex;justify-content:space-between;align-items:center;">
            <b>Scene {s.id} — {s.subtopic}</b>
            <span style="background:{color};color:white;padding:2px 8px;border-radius:12px;font-size:0.8em;">{s.scene_type}</span>
          </div>
          <p style="margin:8px 0 4px 0;"><i>Animation:</i> {s.animation_description}</p>
          <p style="margin:4px 0 0 0;color:#aaa;"><i>Narration:</i> {s.narration}</p>
        </div>
        ''')
    display(HTML("".join(rows)))


def show_scenes_with_audio(scenes):
    for s in scenes:
        color = BADGE_COLOR.get(s.scene_type, "#888")
        duration = s.timestamps[-1].end if s.timestamps else 0.0
        display(HTML(f'''
        <div style="border:1px solid #444;border-radius:8px;padding:12px;margin-bottom:4px;">
          <div style="display:flex;justify-content:space-between;align-items:center;">
            <b>Scene {s.id} — {s.subtopic}</b>
            <span style="background:{color};color:white;padding:2px 8px;border-radius:12px;font-size:0.8em;">{s.scene_type} · {duration:.1f}s</span>
          </div>
          <p style="margin:8px 0 4px 0;color:#aaa;">{s.narration}</p>
        </div>
        '''))
        if s.audio_path:
            display(Audio(filename=s.audio_path))


def show_scenes_with_video(scenes):
    status_color = {"rendered": "#1fa971", "failed": "#d9534f", "not_applicable": "#666"}
    rendered_scenes = [s for s in scenes if s.scene_type in RENDERED_TYPES]
    other_scenes = [s for s in scenes if s.scene_type not in RENDERED_TYPES]
    for s in rendered_scenes:
        color = status_color.get(s.render_status, "#888")
        renderer_badge = BADGE_COLOR.get(s.scene_type, "#888")
        display(HTML(f'''
        <div style="border:1px solid #444;border-radius:8px;padding:12px;margin-bottom:4px;">
          <div style="display:flex;justify-content:space-between;align-items:center;">
            <b>Scene {s.id} — {s.subtopic}</b>
            <span>
              <span style="background:{renderer_badge};color:white;padding:2px 8px;border-radius:12px;font-size:0.8em;">{s.scene_type}</span>
              <span style="background:{color};color:white;padding:2px 8px;border-radius:12px;font-size:0.8em;">{s.render_status} · {s.render_attempts} attempt(s)</span>
            </span>
          </div>
          <p style="margin:8px 0 4px 0;color:#aaa;">{s.last_feedback or ""}</p>
        </div>
        '''))
        if s.video_path:
            display(Video(filename=s.video_path, embed=True, width=480))
    if other_scenes:
        types = ", ".join(sorted({s.scene_type for s in other_scenes}))
        print(f"{len(other_scenes)} scene(s) ({types}) skipped — no renderer built for them yet.")

## Input

Edit these and re-run the notebook from here.

In [6]:
topic = "Hopf Oscillators"
audience = "undergraduate engineering students"
duration_minutes = 12
extra_reference_paths: list[str] = []  # any reference files outside the folder below

directory = project_dir(topic)
references_dir = directory / "references"
references_dir.mkdir(exist_ok=True)

initial_state = VideoState(topic=topic, audience=audience, duration_minutes=duration_minutes)

graph = build_graph()
config = {"configurable": {"thread_id": topic}}

print(f"Project folder: {directory}")
print(f"Drop reference files (.txt / .md / .pdf) here any time before Step 2: {references_dir}")

Project folder: /Users/sindhuramrutha/Documents/cns_lab_files/neurogati/video_engine/projects/hopf-oscillators
Drop reference files (.txt / .md / .pdf) here any time before Step 2: /Users/sindhuramrutha/Documents/cns_lab_files/neurogati/video_engine/projects/hopf-oscillators/references


## Optional: supply your own detailed script (skips Steps 1-2 entirely)

If you'd rather write the content yourself than have Claude invent examples and analogies,
point this at a file (markdown or plain text — sections, examples, whatever you want covered)
and run the cell below. It skips Planner and Detailed Scripter completely — no LLM call
generates any content, your file becomes `detailed_script` directly — and jumps straight to
Step 3 (Scene Script), which turns your content into scene-by-scene narration + animation
shots.

**If you use this, skip Steps 1 and 2 below entirely and go straight to Step 3.**

In [ ]:
own_detailed_script_path = ""  # e.g. "my_content.md" — set this, run this cell, then skip to Step 3

if own_detailed_script_path:
    detailed_script_text = Path(own_detailed_script_path).read_text()
    graph.update_state(
        config,
        {
            "topic": topic,
            "audience": audience,
            "duration_minutes": duration_minutes,
            "detailed_script": detailed_script_text,
        },
        as_node="detailed_scripter",
    )
    state = VideoState.model_validate(graph.get_state(config).values)
    print(f"Loaded {len(detailed_script_text)} chars from {own_detailed_script_path}")
    print("Steps 1 and 2 skipped — no LLM call made. Jump straight to Step 3 below.")
    display(Markdown(f"### Your Detailed Script\n\n{state.detailed_script}"))

## Step 1 — Planner *(skip if you used the optional cell above)*

Calls Claude to produce learning objectives and a teaching plan. The graph pauses here.

In [7]:
result = graph.invoke(initial_state, config=config)
state = VideoState.model_validate(result)

display(Markdown("### Objectives\n" + "\n".join(f"- {o}" for o in state.objectives)))
display(Markdown(f"### Teaching Plan\n\n{state.teaching_plan}"))

### Objectives
- Define a Hopf oscillator as a nonlinear dynamical system exhibiting a stable limit cycle produced by a supercritical Hopf bifurcation.
- Explain how the bifurcation parameter mu controls whether a limit cycle exists and determines its radius.
- Write the Hopf oscillator equations in both Cartesian and polar coordinates and interpret the role of each term.
- Contrast limit-cycle oscillators with linear harmonic oscillators in terms of robustness to perturbation.
- Describe how amplitude and frequency can be tuned independently and how coupling enables entrainment/synchronization.
- Identify a practical engineering use of Hopf oscillators, such as central pattern generators for robot locomotion.

### Teaching Plan

SECTION 1 — Hook: Why rhythm needs robustness (0:00-1:00)
Open with a visual of a walking robot leg or a heartbeat trace being nudged (perturbed) and recovering its rhythm. Pose the question: what kind of math object 'wants' to return to a rhythm after being kicked, unlike a plain sine wave? This motivates the need for a self-correcting oscillator.

SECTION 2 — Linear oscillator vs. limit cycle (1:00-3:00)
Show phase portrait of a simple harmonic oscillator: concentric circles, neutrally stable, any perturbation shifts you to a permanently different orbit (no restoring force in amplitude). Contrast with a phase portrait showing trajectories from both inside and outside spiraling onto one single closed curve — the limit cycle. Key visual: two phase portraits side by side, arrows showing convergence only in the nonlinear case. Intuition: the limit cycle is an attractor, not just a trajectory.

SECTION 3 — The Hopf bifurcation (3:00-5:00)
Introduce a single scalar parameter mu controlling qualitative behavior. Visual: bifurcation diagram — for mu<0 the origin is a stable spiral (decaying to rest); at mu=0 the origin loses stability; for mu>0 a stable circular limit cycle of radius sqrt(mu) appears while the origin becomes unstable. Animate mu sweeping through 0 to show the sudden 'birth' of oscillation. This is the supercritical Hopf bifurcation — the mathematical seed of the oscillator's design.

SECTION 4 — The equations, Cartesian and polar (5:00-7:30)
Present the canonical Hopf oscillator:
x' = (mu - r^2) x - omega y
y' = (mu - r^2) y + omega x, where r^2 = x^2+y^2.
Switch to polar form: r' = r(mu - r^2), theta' = omega.
Visual: vector field arrows in the plane pointing inward when r>sqrt(mu) and outward when r<sqrt(mu), converging on the circle r=sqrt(mu). Emphasize decoupling: r' controls amplitude dynamics only, theta' controls constant angular velocity (frequency) only — a key design feature.

SECTION 5 — Robustness and independent tuning (7:30-9:30)
Demonstrate (verbally/visually) that after a perturbation pushing the state off the circle, the radial equation r'=r(mu-r^2) pulls it back to r=sqrt(mu), while theta keeps advancing at rate omega — so the oscillator recovers amplitude and phase-continues seamlessly. Show how changing mu rescales amplitude (bigger/smaller circle) independent of changing omega (faster/slower rotation), and note this decoupling is rare and valuable — you can adjust stride length and stride frequency separately in a robot leg.

SECTION 6 — Coupling and entrainment (9:30-11:00)
Briefly extend to two coupled Hopf oscillators (add coupling terms k(x2-x1) etc.) and show visually how initially out-of-phase oscillators lock into a common frequency/phase relationship — the basis of synchronized limbs in a gait pattern generator. Mention adaptive-frequency Hopf oscillators that learn the frequency of an external signal by adjusting omega, useful for adapting to disturbances (e.g., syncing to a treadmill speed).

SECTION 7 — Wrap-up and applications (11:00-12:00)
Recap the chain of ideas: linear oscillators lack robustness -> nonlinear limit cycle from Hopf bifurcation provides it -> polar decomposition reveals independent amplitude/frequency control -> coupling enables multi-joint synchronization. Close with the real-world payoff: Hopf oscillators as central pattern generators (CPGs) in legged-robot locomotion control, letting engineers shape rhythmic, perturbation-resistant motion with just a few tunable parameters.

In [ ]:
# Optional: instead of hand-editing files, give a free-text instruction and regenerate.
# Re-run this cell as many times as you want (edit `feedback` each time) before moving on.
feedback = ""  # e.g. "focus this on vibration analysis for mechanical engineers"

if feedback:
    revised = revise_plan(state, feedback)
    graph.update_state(config, revised)
    state = VideoState.model_validate(graph.get_state(config).values)
    display(Markdown("### Objectives\n" + "\n".join(f"- {o}" for o in state.objectives)))
    display(Markdown(f"### Teaching Plan\n\n{state.teaching_plan}"))

In [8]:
# Export — edit these files in any editor if you want changes
objectives_path = directory / "01_objectives.txt"
plan_path = directory / "01_teaching_plan.md"
objectives_path.write_text("\n".join(state.objectives))
plan_path.write_text(state.teaching_plan)
print(f"Wrote {objectives_path}")
print(f"Wrote {plan_path}")

Wrote /Users/sindhuramrutha/Documents/cns_lab_files/neurogati/video_engine/projects/hopf-oscillators/01_objectives.txt
Wrote /Users/sindhuramrutha/Documents/cns_lab_files/neurogati/video_engine/projects/hopf-oscillators/01_teaching_plan.md


In [9]:
# Reload — run this only if you edited the file(s) above; otherwise skip it
enhance_edits = True  # expands rough notes back to full detail; set False to use edits verbatim

edited_objectives = [line for line in objectives_path.read_text().splitlines() if line.strip()]
edited_plan = plan_path.read_text()
if enhance_edits:
    edited_plan = enhance(
        edited_plan,
        context="a structured teaching plan for a STEM educational video, sectioned with timing",
    )
graph.update_state(config, {"objectives": edited_objectives, "teaching_plan": edited_plan})
print("Loaded edits back into the pipeline.")

Loaded edits back into the pipeline.


## Human approval gate 1 — Planner

Review (and optionally edit + reload) the plan above. Run the next cell when you approve it —
that resumes the graph into the Detailed Scripter.

## Step 2 — Detailed Scripter *(skip if you used the optional cell above)*

Calls Claude to turn the approved plan (plus any references) into the full spoken content. The graph pauses again after this.

In [10]:
reference_files = list_reference_files(references_dir) + [
    Path(p) for p in extra_reference_paths
]
references = load_references(reference_files)
graph.update_state(config, {"references": references})
print(f"Loaded {len(references)} reference document(s): {[f.name for f in reference_files]}")

result = graph.invoke(None, config=config)  # resumes from the checkpoint, runs detailed_scripter
state = VideoState.model_validate(result)

display(Markdown(f"### Detailed Script\n\n{state.detailed_script}"))

Loaded 0 reference document(s): []


### Detailed Script

# Hopf Oscillators — Video Script

## SECTION 1 — Hook: Why rhythm needs robustness

Watch a robot leg walking. Someone gives it a shove — a sideways kick mid-stride. A moment later, it's walking again, same rhythm, same stride, like nothing happened.

Now think about a heartbeat. Your heart gets startled, skips, stutters — and within a beat or two, it's back to its steady rhythm.

Here's the question I want you to sit with: what kind of mathematical object *does* that? What equation, when you perturb it, doesn't just wander off to some new behavior — it actively fights to return to the same rhythm it had before?

A plain sine wave doesn't do this. If you nudge a sine wave, it just becomes a different sine wave — same shape, shifted amplitude, and it stays shifted forever. There's nothing in the equation "sine" that says "go back to how you were."

So we need something else — a nonlinear system with a built-in sense of "this is my rhythm, and I'm returning to it." That object exists, it has a name — the Hopf oscillator — and by the end of this video you'll understand exactly why it behaves this way, down to the equations.

## SECTION 2 — Linear oscillator vs. limit cycle

Let's make "lacks robustness" precise. Take the simplest oscillator you know, the linear harmonic oscillator:

$$\ddot{x} + \omega^2 x = 0$$

In the phase plane — position on one axis, velocity on the other — its trajectories are circles (or ellipses), one inside another, like a stack of nested rings. Each circle is a valid orbit, and crucially, *none of them is special*. If you're cruising along the circle of radius 2 and I bump you out to radius 3, you don't fight your way back to radius 2. You just calmly orbit forever at radius 3. There's no restoring force in the amplitude direction — only in position. We call this neutral stability: any perturbation sends you to a permanently different, equally valid orbit.

Now contrast that with a different picture. Imagine a phase portrait where trajectories starting *outside* a certain circle spiral inward toward it, and trajectories starting *inside* that circle spiral outward toward it — from both directions, everything funnels onto one single closed curve. That special curve is called a **limit cycle**.

The key conceptual shift: a limit cycle isn't just *a* trajectory — it's an **attractor**. It's the one path in the whole plane that every nearby trajectory gets pulled onto, from inside or outside. That's the mathematical signature of "wanting to return to a rhythm."

## SECTION 3 — The Hopf bifurcation

So where does a limit cycle like that actually come from? We need one more ingredient: a single control knob, a parameter we'll call $\mu$, that determines whether this attracting rhythm exists at all.

Picture this: for $\mu < 0$, the origin — the point of rest — is a stable spiral. Any trajectory nearby just spirals inward and dies out, decaying to zero. There's no oscillation; the system settles to stillness.

At exactly $\mu = 0$, something changes: the origin loses its grip. It's right on the boundary between stable and unstable.

Then for $\mu > 0$, two things happen simultaneously: the origin flips to become *unstable* — nearby trajectories now spiral *away* from it — and at the same time, a brand-new stable limit cycle is born, a perfect circle of radius

$$r = \sqrt{\mu}$$

As $\mu$ increases from negative to positive, you'd see the system suddenly "switch on" — oscillation appears out of nowhere, growing from zero radius and expanding as $\sqrt{\mu}$ grows. This qualitative event — stability trading hands between a fixed point and a newborn circle — is called a **supercritical Hopf bifurcation**. It's the mathematical seed from which we're going to grow our entire oscillator design.

## SECTION 4 — The equations, Cartesian and polar

Let's write down the actual equations that produce exactly this behavior. This is the canonical Hopf oscillator:

$$\dot{x} = (\mu - r^2)\,x - \omega\, y$$
$$\dot{y} = (\mu - r^2)\,y + \omega\, x$$

where $r^2 = x^2 + y^2$.

At first glance this looks like a tangle of coupled terms. But here's the trick: switch to polar coordinates, $x = r\cos\theta$, $y = r\sin\theta$. Substituting in and simplifying, this exact same system becomes stunningly simple:

$$\dot{r} = r(\mu - r^2)$$
$$\dot{\theta} = \omega$$

Look at what just happened. The system *decoupled*. The radial equation, $\dot r = r(\mu - r^2)$, only knows about $r$ — it governs amplitude, and amplitude alone. The angular equation, $\dot\theta = \omega$, says the angle simply increases at a constant rate $\omega$ — that's the frequency, full stop, with nothing else influencing it.

Let's read the radial equation like a vector field. If $r > \sqrt{\mu}$, then $\mu - r^2 < 0$, so $\dot r < 0$ — the radius shrinks, pulled inward. If $r < \sqrt{\mu}$, then $\mu - r^2 > 0$, so $\dot r > 0$ — the radius grows, pushed outward. Either way, you're driven toward $r = \sqrt{\mu}$ exactly. That's the limit cycle we drew in Section 3, now derived directly from the equations: arrows pointing inward from outside the circle, arrows pointing outward from inside, all converging on one ring.

This is the key design feature of the Hopf oscillator: **amplitude dynamics and frequency dynamics live in completely separate equations.**

## SECTION 5 — Robustness and independent tuning

Let's connect this back to our opening hook. Suppose the system is happily cycling on $r = \sqrt{\mu}$, and something perturbs it — kicks it to a new radius, say knocks $r$ up to $\sqrt{\mu} + \delta$ for some disturbance $\delta$. What happens?

The radial equation immediately takes over: since we're now outside the target radius, $\dot r < 0$, and $r$ relaxes back down to $\sqrt{\mu}$. Meanwhile — and this is the elegant part — $\theta$ was completely unaffected by any of this. It kept advancing at rate $\omega$ the entire time, undisturbed. So the system doesn't reset or freeze; it simply resumes its rhythm in stride, with amplitude restored and phase having continued seamlessly through the disturbance. That is exactly the self-correcting behavior we saw in the walking robot leg and the heartbeat.

Now here's the payoff for an engineer: because $\mu$ and $\omega$ appear in separate equations, you can tune them completely independently.

- Turning up $\mu$ makes $\sqrt{\mu}$ bigger — a larger-radius limit cycle, a bigger oscillation amplitude — without touching the frequency at all.
- Turning up $\omega$ makes the system rotate faster around whatever circle it's on — a higher frequency — without touching the amplitude at all.

This kind of clean decoupling is actually rare in nonlinear systems, and it's enormously valuable in practice. Think of a robot leg: $\mu$ sets your **stride length**, $\omega$ sets your **stride frequency** — and you can dial each one up or down separately, exactly like adjusting two separate knobs on a machine, instead of fighting a system where every parameter smears into every behavior.

## SECTION 6 — Coupling and entrainment

One oscillator gives you one rhythmic joint. A real legged robot has several joints that all need to move in a coordinated rhythm — same frequency, specific phase relationships (front-left leg out of phase with front-right, and so on).

The way to get that is to couple multiple Hopf oscillators together. Take two oscillators, each with its own $(x_1,y_1)$ and $(x_2,y_2)$, and add a coupling term that nudges each one toward the other's current state, something like:

$$\dot{x}_1 = (\mu - r_1^2)x_1 - \omega y_1 + k(x_2 - x_1)$$

with the analogous term added for oscillator 2. Here $k$ controls how strongly they influence each other.

Even if the two oscillators start completely out of phase — one at the peak of its cycle while the other is at the trough — this coupling term continually nudges them toward each other, and after a short transient they **lock together**: same frequency, and a fixed, stable phase relationship. This phenomenon is called **entrainment**, or synchronization, and it's the mathematical basis for how a set of coupled Hopf oscillators can serve as a central pattern generator — producing the coordinated multi-limb rhythm of a walking gait from a small network of simple, coupled equations.

It's worth mentioning one more extension: **adaptive-frequency Hopf oscillators**, where $\omega$ itself is no longer fixed but slowly adjusts based on an external signal — say, sensor feedback from the ground, or the speed of a treadmill. The oscillator literally learns to match its frequency to whatever rhythm it's sensing in the environment, letting a robot adapt its gait on the fly to a changing terrain or speed, without anyone reprogramming it.

## SECTION 7 — Wrap-up and applications

Let's retrace the chain of ideas we built. A plain linear oscillator has no memory of its rhythm — perturb it, and it happily settles into a new, permanently different orbit. To fix that, we needed an attractor for the orbit itself — a limit cycle — and we saw that a limit cycle is born exactly at a supercritical Hopf bifurcation, when a single parameter $\mu$ crosses zero. Writing the resulting equations in polar form revealed the real design secret: amplitude, governed by $\mu$ through $\dot r = r(\mu - r^2)$, and frequency, governed by $\omega$ through $\dot\theta = \omega$, are completely decoupled — so you get independent, robust control over both.

And when you couple several of these oscillators together, they entrain into synchronized, phase-locked rhythms — exactly the coordination a multi-legged robot needs.

That's the real-world payoff: Hopf oscillators, used as central pattern generators, let engineers shape rhythmic, perturbation-resistant motion for legged robots using just a handful of tunable parameters — $\mu$ for amplitude, $\omega$ for frequency, and $k$ for coordination between limbs — turning a few lines of nonlinear differential equations into a walking, self-correcting gait.

In [ ]:
# Optional: instead of hand-editing the file, give a free-text instruction and regenerate.
# Re-run this cell as many times as you want (edit `feedback` each time) before moving on.
feedback = ""  # e.g. "add a worked example to the section on eigenvalues"

if feedback:
    revised = revise_script(state, feedback)
    graph.update_state(config, revised)
    state = VideoState.model_validate(graph.get_state(config).values)
    display(Markdown(f"### Detailed Script\n\n{state.detailed_script}"))

In [11]:
# Export — edit this file if you want changes
script_path = directory / "02_detailed_script.md"
script_path.write_text(state.detailed_script)
print(f"Wrote {script_path}")

Wrote /Users/sindhuramrutha/Documents/cns_lab_files/neurogati/video_engine/projects/hopf-oscillators/02_detailed_script.md


In [12]:
# Reload — run this only if you edited the file above; otherwise skip it
enhance_edits = True  # expands rough notes back to full detail; set False to use edits verbatim

edited_script = script_path.read_text()
if enhance_edits:
    edited_script = enhance(
        edited_script,
        context=(
            "a detailed spoken STEM educational script, organized by subtopic, with "
            "narration, equations, analogies, and examples"
        ),
    )
graph.update_state(config, {"detailed_script": edited_script})
print("Loaded edits back into the pipeline.")

Loaded edits back into the pipeline.


## Human approval gate 2 — Detailed Scripter

Review (and optionally edit + reload) the script above. Run the next cell when you approve it —
that resumes the graph into the Audio-Visual Scene Script agent.

## Step 3 — Audio-Visual Scene Script

Calls Claude to break the script into scenes, each with narration, an animation description, and a manim/react/image_only/audio_only classification.

In [13]:
result = graph.invoke(None, config=config)  # resumes from the checkpoint, runs scene_script
state = VideoState.model_validate(result)

show_scenes(state.scenes)

In [ ]:
# Optional: instead of hand-editing the JSON, give a free-text instruction and regenerate.
# Re-run this cell as many times as you want (edit `feedback` each time) before moving on.
feedback = ""  # e.g. "split the equation-derivation scene into two shorter scenes"

if feedback:
    revised = revise_scenes(state, feedback)
    graph.update_state(config, revised)
    state = VideoState.model_validate(graph.get_state(config).values)
    show_scenes(state.scenes)

In [14]:
# Export — edit this file if you want changes (add/remove/reorder scenes, change scene_type, etc.)
scenes_path = directory / "03_scenes.json"
scenes_path.write_text(json.dumps([s.model_dump() for s in state.scenes], indent=2))
print(f"Wrote {scenes_path}")

Wrote /Users/sindhuramrutha/Documents/cns_lab_files/neurogati/video_engine/projects/hopf-oscillators/03_scenes.json


In [15]:
# Reload — run this only if you edited the file above; otherwise skip it
enhance_edits = True  # expands rough notes back to full detail; set False to use edits verbatim

raw_scenes = scenes_path.read_text()
if enhance_edits:
    raw_scenes = enhance(
        raw_scenes,
        context=(
            "a JSON array of scenes for a STEM educational video: each has subtopic, "
            "narration (spoken text), animation_description, and scene_type "
            "(manim/react/image_only/audio_only)"
        ),
    )
edited_scenes = [Scene(**item) for item in json.loads(raw_scenes)]
graph.update_state(config, {"scenes": edited_scenes})
state = VideoState.model_validate(graph.get_state(config).values)
show_scenes(state.scenes)

Deserializing unregistered type state.Scene from checkpoint. This will be blocked in a future version. Set LANGGRAPH_STRICT_MSGPACK=true to block now, or add to allowed_msgpack_modules to allow explicitly: [('state', 'Scene')]


## Human approval gate 3 — Scene Script

Review (and optionally edit + reload) the scenes above. Run the next cell when you approve
them — that resumes the graph into the Audio Generator. Not happy with a scene's narration?
Edit it in `03_scenes.json` above, reload, then run Step 4.

## Step 4 — Audio Generator

Synthesizes narration audio per scene (Piper TTS) and aligns word-level timestamps (Whisper,
local, CPU). No LLM call here — deterministic tool execution. Takes a minute or two for ~20
scenes on CPU.

In [16]:
result = graph.invoke(None, config=config)  # resumes from the checkpoint, runs audio_generator
state = VideoState.model_validate(result)

show_scenes_with_audio(state.scenes)

## Human approval gate 4 — Audio

Listen to each scene above. If the pacing or pronunciation is off, edit the narration in
`03_scenes.json`, reload it (Step 3's reload cell), then re-run Step 4.

## Step 5 — Visual Render (interactive, one scene at a time)

For each manim/matplotlib scene: renders once (no automated aesthetic critique — that was
burning API calls on a judgment you're about to make yourself). You'll see the clip, then a
text prompt: type feedback to regenerate that scene (as many rounds as you want), or press
Enter to accept and move to the next scene.

**Must be run interactively in Jupyter** (needs your input at each scene) — this cell will hang
if executed headlessly (e.g. `nbconvert --execute`). image_only/audio_only scenes are skipped
automatically (no renderer built for them yet).

In [ ]:
project_root = project_dir(topic)
reviewed_scenes = []

for scene in state.scenes:
    render = RENDERERS.get(scene.scene_type)
    if render is None:
        print(f"Scene {scene.id} ({scene.scene_type}): no renderer yet, skipping.")
        reviewed_scenes.append(scene)
        continue

    scene = render(scene, project_root)
    while True:
        show_scenes_with_video([scene])
        feedback = input(f"Scene {scene.id} — feedback to revise, or Enter to accept: ").strip()
        if not feedback:
            break
        scene = render(scene, project_root, instruction=feedback)
    reviewed_scenes.append(scene)

# Tell the graph this stage is done (without re-running the batch node) and move state forward
graph.update_state(config, {"scenes": reviewed_scenes}, as_node="visual_render")
state = VideoState.model_validate(graph.get_state(config).values)
print(f"\nAll {len(reviewed_scenes)} scenes reviewed.")

## Human approval gate 5 — Rendered clips

Review each clip above, **before audio gets joined to it**. Scenes marked "needs_review"
exhausted their auto-critique retries — look at those first. There's no re-render-single-scene
control yet; for now, fixing a scene means editing its `animation_description` in
`03_scenes.json`, reloading (Step 3's reload cell), and re-running Step 5 for everyone.

## Step 6 — Compose

Merges each scene's video with its narration audio, length-locked to the audio (the source of
truth for timing). Scenes without a rendered clip (image_only/audio_only) get a plain title-card
placeholder for now — there's no illustration generator yet, this just keeps the pipeline
complete end to end. Deterministic — no LLM call, so this is fast and cheap to re-run.

In [ ]:
result = graph.invoke(None, config=config)  # resumes from the checkpoint, runs compose
state = VideoState.model_validate(result)

for s in state.scenes:
    print(f"scene {s.id}: {s.composed_path}")

## Human approval gate 6 — Composed scenes

Spot-check a few composed clips in `projects/<slug>/composed/` if you want (they're plain files,
open them in any player). Run the next cell when ready to stitch everything into the final video.

## Step 7 — Finalize

Stitches every composed scene into the final video and generates subtitles — from the same
word-alignment timestamps that drove animation timing, not a second speech-recognition pass, so
audio/video/subtitles can't drift out of sync with each other.

In [ ]:
result = graph.invoke(None, config=config)  # resumes from the checkpoint, runs finalize
state = VideoState.model_validate(result)

print(f"Final video: {state.final_video_path}")
print(f"Subtitles:   {state.subtitles_path}")
display(Video(filename=state.final_video_path, embed=True, width=640))

## Save

Persists the full pipeline state — topic, plan, script, scenes, all paths — for next time.

In [13]:
out_path = save_state(state, directory)
print(f"Saved to {out_path}")

Saved to /Users/sindhuramrutha/Documents/cns_lab_files/neurogati/video_engine/projects/hopf-oscillators/state.json


## Human approval gate 7 — Final video

Watch the video above. **Not happy with something? Go back and reiterate, don't start over:**
- Wrong content/pacing → edit `01_teaching_plan.md` or `02_detailed_script.md`, reload at that gate, re-run every step after it.
- Wrong scene breakdown or scene type → edit `03_scenes.json`, reload at gate 3, re-run Steps 4-7.
- A specific clip looks wrong → edit that scene's `animation_description` in `03_scenes.json`, reload, re-run Step 5 onward.
- Narration wording/pacing off → edit the scene's `narration` in `03_scenes.json`, reload, re-run Step 4 onward (audio depends on narration text).

Every stage is a plain file — there's no black box step you can't inspect or hand-edit.

Not built yet: real illustrations for image_only/audio_only scenes (currently a plain title card), and a JS/Motion-Canvas renderer for scenes Manim/Matplotlib can't cover.